In [1]:
import hashlib
import math  # noqa: I001
import numpy
import pathlib
import polars as pl
import time

import xy.pyplot as plt

for path in pathlib.Path("attachments").iterdir():
    if path.name.startswith("v2_"):
        pass
    else:
        path.unlink()

pins = {}


def saveText(digits, name, text):
    with pl.Config(
        tbl_rows=-1, tbl_cols=-1, tbl_width_chars=1000, fmt_str_lengths=1000
    ):
        content = str(text)
    print(name, digits)
    print(content)
    pathlib.Path(f"attachments/v2_{name}_{digits}.txt").write_text(
        content + "\n", encoding="utf-8"
    )


def savePins(digits):
    pins[digits] = (
        pl.scan_csv(f"data/pins_{digits}.csv", infer_schema_length=0)
        .with_columns(pl.col("pin").cast(pl.UInt32), pl.col("n").cast(pl.Int64))
        .sort("n", descending=True)
        .with_columns(
            probability=pl.col("n") / pl.col("n").sum(),
            rank=pl.int_range(1, pl.len() + 1, dtype=pl.UInt32),
        )
        .collect(engine="streaming")
    )


def saveDigitColumns(digits):
    pins[digits] = pins[digits].with_columns(
        **{
            f"digit_{position}": (
                (pl.col("pin") // 10 ** (digits - 1 - position)) % 10
            ).cast(pl.Int8)
            for position in range(digits)
        }
    )


def showTopPins(digits):
    saveText(
        digits,
        "top_pins",
        pins[digits]
        .head(20)
        .with_columns(pl.col("pin").cast(pl.String).str.zfill(digits)),
    )


def showTotalOccurrences(digits):
    saveText(digits, "total_occurrences", pins[digits]["n"].sum())


def getHalf(digits, step=1000000):
    counts = pins[digits]["n"]
    total = int(counts.sum())
    running = 0
    for start in range(0, counts.len(), step):
        chunk = counts.slice(start, step).to_numpy()
        cumulative = running + numpy.cumsum(chunk)
        index = int(numpy.searchsorted(2 * cumulative, total))
        if index < chunk.size:
            return start + index + 1
        else:
            running = int(cumulative[-1])
    return counts.len()


def showEntropy(digits):
    saveText(
        digits,
        "entropy",
        pins[digits]
        .lazy()
        .filter(pl.col("n") > 0)
        .select(
            entropy=-(pl.col("probability") * pl.col("probability").log(2)).sum(),
            minimum=-pl.col("probability").max().log(2),
            guesswork=(pl.col("probability") * pl.col("rank")).sum(),
            maximum=pl.lit(digits * math.log2(10)),
        )
        .with_columns(
            half=pl.lit(getHalf(digits), dtype=pl.UInt32),
            guesswork_bits=(2 * pl.col("guesswork") - 1).log(2),
        )
        .select(
            "entropy", "minimum", "guesswork", "half", "maximum", "guesswork_bits"
        )
        .collect(engine="streaming"),
    )
    saveText(
        digits,
        "coverage",
        pl.DataFrame(
            [
                (top, pins[digits]["probability"].head(top).sum())
                for top in (
                    3,
                    6,
                    10,
                    30,
                    100,
                    1000,
                    10000,
                    10**digits // 100,
                    10**digits // 10,
                )
            ],
            schema=["top", "coverage"],
            orient="row",
        ),
    )


def showHeatmap(digits):
    pairLength = min(2, digits // 2)
    grid = numpy.zeros((10**pairLength, 10**pairLength))
    summary = (
        pins[digits]
        .lazy()
        .group_by(
            (pl.col("pin") // 10 ** (digits - pairLength)).alias("row"),
            (pl.col("pin") % 10**pairLength).alias("column"),
        )
        .agg(pl.col("n").sum())
        .collect(engine="streaming")
    )
    grid[summary["row"].to_numpy(), summary["column"].to_numpy()] = summary[
        "n"
    ].to_numpy()
    plt.figure(figsize=(10, 8))
    plt.imshow(numpy.log1p(grid), cmap="magma", origin="lower")
    plt.colorbar(label="log(1 + occurrences)")
    plt.title(f"Heatmap of {digits}-digits PIN numbers")

    plt.xlabel("last digits")

    plt.ylabel("first digits")
    plt.savefig(f"attachments/v2_heatmap_{digits}.png", dpi=300)
    plt.show()


def showRankFrequency(digits):
    positive = pins[digits].select("n").filter(pl.col("n") > 0)["n"]
    ranks = numpy.unique(numpy.geomspace(1, positive.len(), 5000).astype(numpy.int64))
    plt.figure(figsize=(10, 6))
    plt.loglog(ranks, positive[ranks - 1].to_numpy())
    plt.title(f"Rank-Frequency Plot of {digits}-digits PIN numbers")

    plt.xlabel("rank")

    plt.ylabel("occurrences")
    plt.savefig(f"attachments/v2_rank_frequency_{digits}.png", dpi=300)
    plt.show()


def showTopBars(digits):
    top = pins[digits].head(20)
    plt.figure(figsize=(10, 6))
    plt.bar(top["pin"].cast(pl.String).str.zfill(digits).to_list(), top["n"].to_list())
    plt.xticks(rotation=60)
    plt.title(f"Top 20 {digits}-digits PIN numbers")

    plt.xlabel("PIN")

    plt.ylabel("occurrences")
    plt.tight_layout()
    plt.savefig(f"attachments/v2_top_bars_{digits}.png", dpi=300)
    plt.show()


def showDigitFrequency(digits):
    grid = numpy.zeros((10, digits))
    for position in range(digits):
        summary = (
            pins[digits]
            .lazy()
            .group_by(f"digit_{position}")
            .agg(pl.col("n").sum())
            .collect(engine="streaming")
        )
        grid[summary[f"digit_{position}"].to_numpy(), position] = summary[
            "n"
        ].to_numpy()
    grid = grid / grid.sum(axis=0)
    plt.figure(figsize=(10, 6))
    plt.imshow(grid, cmap="viridis", aspect="auto")
    plt.colorbar(label="share of occurrences")
    plt.xticks(range(digits), range(1, digits + 1))
    plt.yticks(range(10))
    plt.title(f"Digit Frequency Plot of {digits}-digits PIN numbers")

    plt.xlabel("position")

    plt.ylabel("digit")
    plt.savefig(f"attachments/v2_digit_frequency_{digits}.png", dpi=300)
    plt.show()


def showYearFrequency(digits):
    if digits == 4:
        years = (
            pins[digits]
            .lazy()
            .filter((pl.col("pin") >= 1900) & (pl.col("pin") <= 2025))
            .sort("pin")
            .select("pin", "probability")
            .collect(engine="streaming")
        )
        plt.figure(figsize=(10, 6))
        plt.plot(years["pin"].to_numpy(), years["probability"].to_numpy())
        plt.title(f"Year Frequency Plot of {digits}-digits PIN numbers")

        plt.xlabel("year")

        plt.ylabel("probability")
        plt.savefig(f"attachments/v2_year_frequency_{digits}.png", dpi=300)
        plt.show()
    else:
        pass

In [2]:
for digits in range(3, 9):
    if digits == 7:
        continue
    else:
        savePins(digits)
        saveDigitColumns(digits)
        showTopPins(digits)
        showTotalOccurrences(digits)
        showEntropy(digits)
        showHeatmap(digits)
        showRankFrequency(digits)
        showTopBars(digits)
        showDigitFrequency(digits)
        showYearFrequency(digits)

top_pins 3
shape: (20, 7)
┌─────┬─────────┬─────────────┬──────┬─────────┬─────────┬─────────┐
│ pin ┆ n       ┆ probability ┆ rank ┆ digit_0 ┆ digit_1 ┆ digit_2 │
│ --- ┆ ---     ┆ ---         ┆ ---  ┆ ---     ┆ ---     ┆ ---     │
│ str ┆ i64     ┆ f64         ┆ u32  ┆ i8      ┆ i8      ┆ i8      │
╞═════╪═════════╪═════════════╪══════╪═════════╪═════════╪═════════╡
│ 123 ┆ 1783558 ┆ 0.29559     ┆ 1    ┆ 1       ┆ 2       ┆ 3       │
│ 666 ┆ 204408  ┆ 0.033877    ┆ 2    ┆ 6       ┆ 6       ┆ 6       │
│ 111 ┆ 129179  ┆ 0.021409    ┆ 3    ┆ 1       ┆ 1       ┆ 1       │
│ 100 ┆ 67997   ┆ 0.011269    ┆ 4    ┆ 1       ┆ 0       ┆ 0       │
│ 000 ┆ 51940   ┆ 0.008608    ┆ 5    ┆ 0       ┆ 0       ┆ 0       │
│ 777 ┆ 39170   ┆ 0.006492    ┆ 6    ┆ 7       ┆ 7       ┆ 7       │
│ 321 ┆ 31477   ┆ 0.005217    ┆ 7    ┆ 3       ┆ 2       ┆ 1       │
│ 555 ┆ 29945   ┆ 0.004963    ┆ 8    ┆ 5       ┆ 5       ┆ 5       │
│ 333 ┆ 28504   ┆ 0.004724    ┆ 9    ┆ 3       ┆ 3       ┆ 3       │
│ 456 ┆ 

top_pins 4
shape: (20, 8)
┌──────┬─────────┬─────────────┬──────┬─────────┬─────────┬─────────┬─────────┐
│ pin  ┆ n       ┆ probability ┆ rank ┆ digit_0 ┆ digit_1 ┆ digit_2 ┆ digit_3 │
│ ---  ┆ ---     ┆ ---         ┆ ---  ┆ ---     ┆ ---     ┆ ---     ┆ ---     │
│ str  ┆ i64     ┆ f64         ┆ u32  ┆ i8      ┆ i8      ┆ i8      ┆ i8      │
╞══════╪═════════╪═════════════╪══════╪═════════╪═════════╪═════════╪═════════╡
│ 1234 ┆ 2633239 ┆ 0.090089    ┆ 1    ┆ 1       ┆ 2       ┆ 3       ┆ 4       │
│ 1111 ┆ 460710  ┆ 0.015762    ┆ 2    ┆ 1       ┆ 1       ┆ 1       ┆ 1       │
│ 0000 ┆ 327795  ┆ 0.011215    ┆ 3    ┆ 0       ┆ 0       ┆ 0       ┆ 0       │
│ 1342 ┆ 168286  ┆ 0.005757    ┆ 4    ┆ 1       ┆ 3       ┆ 4       ┆ 2       │
│ 1212 ┆ 117477  ┆ 0.004019    ┆ 5    ┆ 1       ┆ 2       ┆ 1       ┆ 2       │
│ 2222 ┆ 84527   ┆ 0.002892    ┆ 6    ┆ 2       ┆ 2       ┆ 2       ┆ 2       │
│ 4444 ┆ 83731   ┆ 0.002865    ┆ 7    ┆ 4       ┆ 4       ┆ 4       ┆ 4       │
│ 1122 ┆ 80194

top_pins 5
shape: (20, 9)
┌───────┬─────────┬─────────────┬──────┬─────────┬─────────┬─────────┬─────────┬─────────┐
│ pin   ┆ n       ┆ probability ┆ rank ┆ digit_0 ┆ digit_1 ┆ digit_2 ┆ digit_3 ┆ digit_4 │
│ ---   ┆ ---     ┆ ---         ┆ ---  ┆ ---     ┆ ---     ┆ ---     ┆ ---     ┆ ---     │
│ str   ┆ i64     ┆ f64         ┆ u32  ┆ i8      ┆ i8      ┆ i8      ┆ i8      ┆ i8      │
╞═══════╪═════════╪═════════════╪══════╪═════════╪═════════╪═════════╪═════════╪═════════╡
│ 12345 ┆ 3508324 ┆ 0.162729    ┆ 1    ┆ 1       ┆ 2       ┆ 3       ┆ 4       ┆ 5       │
│ 11111 ┆ 402673  ┆ 0.018677    ┆ 2    ┆ 1       ┆ 1       ┆ 1       ┆ 1       ┆ 1       │
│ 55555 ┆ 188829  ┆ 0.008759    ┆ 3    ┆ 5       ┆ 5       ┆ 5       ┆ 5       ┆ 5       │
│ 12413 ┆ 162719  ┆ 0.007547    ┆ 4    ┆ 1       ┆ 2       ┆ 4       ┆ 1       ┆ 3       │
│ 00000 ┆ 154289  ┆ 0.007156    ┆ 5    ┆ 0       ┆ 0       ┆ 0       ┆ 0       ┆ 0       │
│ 54321 ┆ 122849  ┆ 0.005698    ┆ 6    ┆ 5       ┆ 4       ┆ 3  

top_pins 6
shape: (20, 10)
┌────────┬──────────┬─────────────┬──────┬─────────┬─────────┬─────────┬─────────┬─────────┬─────────┐
│ pin    ┆ n        ┆ probability ┆ rank ┆ digit_0 ┆ digit_1 ┆ digit_2 ┆ digit_3 ┆ digit_4 ┆ digit_5 │
│ ---    ┆ ---      ┆ ---         ┆ ---  ┆ ---     ┆ ---     ┆ ---     ┆ ---     ┆ ---     ┆ ---     │
│ str    ┆ i64      ┆ f64         ┆ u32  ┆ i8      ┆ i8      ┆ i8      ┆ i8      ┆ i8      ┆ i8      │
╞════════╪══════════╪═════════════╪══════╪═════════╪═════════╪═════════╪═════════╪═════════╪═════════╡
│ 123456 ┆ 42542807 ┆ 0.133279    ┆ 1    ┆ 1       ┆ 2       ┆ 3       ┆ 4       ┆ 5       ┆ 6       │
│ 111111 ┆ 5070941  ┆ 0.015886    ┆ 2    ┆ 1       ┆ 1       ┆ 1       ┆ 1       ┆ 1       ┆ 1       │
│ 123123 ┆ 3897129  ┆ 0.012209    ┆ 3    ┆ 1       ┆ 2       ┆ 3       ┆ 1       ┆ 2       ┆ 3       │
│ 000000 ┆ 3166772  ┆ 0.009921    ┆ 4    ┆ 0       ┆ 0       ┆ 0       ┆ 0       ┆ 0       ┆ 0       │
│ 123321 ┆ 1754275  ┆ 0.005496    ┆ 5    ┆ 1  

top_pins 8
shape: (20, 12)
┌──────────┬──────────┬─────────────┬──────┬─────────┬─────────┬─────────┬─────────┬─────────┬─────────┬─────────┬─────────┐
│ pin      ┆ n        ┆ probability ┆ rank ┆ digit_0 ┆ digit_1 ┆ digit_2 ┆ digit_3 ┆ digit_4 ┆ digit_5 ┆ digit_6 ┆ digit_7 │
│ ---      ┆ ---      ┆ ---         ┆ ---  ┆ ---     ┆ ---     ┆ ---     ┆ ---     ┆ ---     ┆ ---     ┆ ---     ┆ ---     │
│ str      ┆ i64      ┆ f64         ┆ u32  ┆ i8      ┆ i8      ┆ i8      ┆ i8      ┆ i8      ┆ i8      ┆ i8      ┆ i8      │
╞══════════╪══════════╪═════════════╪══════╪═════════╪═════════╪═════════╪═════════╪═════════╪═════════╪═════════╪═════════╡
│ 12345678 ┆ 39918339 ┆ 0.050285    ┆ 1    ┆ 1       ┆ 2       ┆ 3       ┆ 4       ┆ 5       ┆ 6       ┆ 7       ┆ 8       │
│ 11223344 ┆ 1996325  ┆ 0.002515    ┆ 2    ┆ 1       ┆ 1       ┆ 2       ┆ 2       ┆ 3       ┆ 3       ┆ 4       ┆ 4       │
│ 11111111 ┆ 1992941  ┆ 0.002511    ┆ 3    ┆ 1       ┆ 1       ┆ 1       ┆ 1       ┆ 1       ┆ 1  

entropy 8
shape: (1, 6)
┌───────────┬──────────┬───────────────┬───────┬───────────┬────────────────┐
│ entropy   ┆ minimum  ┆ guesswork     ┆ half  ┆ maximum   ┆ guesswork_bits │
│ ---       ┆ ---      ┆ ---           ┆ ---   ┆ ---       ┆ ---            │
│ f64       ┆ f64      ┆ f64           ┆ u32   ┆ f64       ┆ f64            │
╞═══════════╪══════════╪═══════════════╪═══════╪═══════════╪════════════════╡
│ 18.651222 ┆ 4.313726 ┆ 903018.282541 ┆ 49064 ┆ 26.575425 ┆ 20.784395      │
└───────────┴──────────┴───────────────┴───────┴───────────┴────────────────┘
coverage 8
shape: (9, 2)
┌──────────┬──────────┐
│ top      ┆ coverage │
│ ---      ┆ ---      │
│ i64      ┆ f64      │
╞══════════╪══════════╡
│ 3        ┆ 0.05531  │
│ 6        ┆ 0.062307 │
│ 10       ┆ 0.067583 │
│ 30       ┆ 0.076251 │
│ 100      ┆ 0.090449 │
│ 1000     ┆ 0.131608 │
│ 10000    ┆ 0.280702 │
│ 1000000  ┆ 0.817924 │
│ 10000000 ┆ 0.98029  │
└──────────┴──────────┘


In [3]:
def isValidDate(day, month):
    return (
        (month >= 1)
        & (month <= 12)
        & (day >= 1)
        & (
            day
            <= pl.when(month == 2)
            .then(29)
            .when(month.is_in([4, 6, 9, 11]))
            .then(30)
            .otherwise(31)
        )
    )


def getNumber(digits, start, length):
    return (pl.col("pin") // 10 ** (digits - start - length)) % 10**length


def getStepExpressions(digits):
    return [
        pl.col(f"digit_{position + 1}") - pl.col(f"digit_{position}")
        for position in range(digits - 1)
    ]


def getDistinctExpression(digits):
    return pl.sum_horizontal(
        [
            pl.any_horizontal(
                [pl.col(f"digit_{position}") == value for position in range(digits)]
            )
            for value in range(10)
        ]
    )


def getKeypadSteps(digits):
    digitColumns = [pl.col(f"digit_{position}") for position in range(digits)]
    rowColumns = [
        pl.when(digit == 0).then(pl.lit(3, dtype=pl.Int8)).otherwise((digit - 1) // 3)
        for digit in digitColumns
    ]
    columnColumns = [
        pl.when(digit == 0).then(pl.lit(1, dtype=pl.Int8)).otherwise((digit - 1) % 3)
        for digit in digitColumns
    ]
    return [
        rowColumns[position + 1] - rowColumns[position]
        for position in range(digits - 1)
    ], [
        columnColumns[position + 1] - columnColumns[position]
        for position in range(digits - 1)
    ]


def getKeypadShapeFlags(digits):
    if digits == 4:
        digitColumns = [pl.col(f"digit_{position}") for position in range(digits)]
        allDistinct = getDistinctExpression(digits) == 4
        return {
            "corners": pl.all_horizontal(
                [digit.is_in([1, 3, 7, 9]) for digit in digitColumns]
            )
            & allDistinct,
            "cross": pl.all_horizontal(
                [digit.is_in([2, 4, 6, 8]) for digit in digitColumns]
            )
            & allDistinct,
            "box": pl.any_horizontal(
                [
                    pl.all_horizontal([digit.is_in(keys) for digit in digitColumns])
                    for keys in ([1, 2, 4, 5], [2, 3, 5, 6], [4, 5, 7, 8], [5, 6, 8, 9])
                ]
            )
            & allDistinct,
        }
    else:
        return {}


def getDateFlags(digits):
    if digits == 4:
        firstPair = getNumber(digits, 0, 2)
        lastPair = getNumber(digits, 2, 2)
        year = getNumber(digits, 0, 4)
        dayMonth = isValidDate(firstPair, lastPair)
        monthDay = isValidDate(lastPair, firstPair)
        recentYear = (year >= 1900) & (year <= 2029)
        return dict(  # noqa: C408
            ddmm=dayMonth,
            mmdd=monthDay,
            any_date=dayMonth | monthDay,
            mmyy=(firstPair >= 1) & (firstPair <= 12),
            year_1900_2029=recentYear,
            year_1940_2009=(year >= 1940) & (year <= 2009),
            year_1956_2015=(year >= 1956) & (year <= 2015),
            year_or_date=dayMonth | monthDay | recentYear,
        )
    elif digits == 6:
        firstPair = getNumber(digits, 0, 2)
        middlePair = getNumber(digits, 2, 2)
        lastPair = getNumber(digits, 4, 2)
        dayMonthYear = isValidDate(firstPair, middlePair)
        monthDayYear = isValidDate(middlePair, firstPair)
        yearMonthDay = isValidDate(lastPair, middlePair)
        return {
            "ddmmyy": dayMonthYear,
            "mmddyy": monthDayYear,
            "yymmdd": yearMonthDay,
            "any_date": dayMonthYear | monthDayYear | yearMonthDay,
        }
    elif digits == 8:
        firstPair = getNumber(digits, 0, 2)
        secondPair = getNumber(digits, 2, 2)
        thirdPair = getNumber(digits, 4, 2)
        fourthPair = getNumber(digits, 6, 2)
        leadingYear = getNumber(digits, 0, 4)
        trailingYear = getNumber(digits, 4, 4)
        dayMonthYear = (
            isValidDate(firstPair, secondPair)
            & (trailingYear >= 1900)
            & (trailingYear <= 2099)
        )
        monthDayYear = (
            isValidDate(secondPair, firstPair)
            & (trailingYear >= 1900)
            & (trailingYear <= 2099)
        )
        yearMonthDay = (
            isValidDate(fourthPair, thirdPair)
            & (leadingYear >= 1900)
            & (leadingYear <= 2099)
        )
        return {
            "ddmmyyyy": dayMonthYear,
            "mmddyyyy": monthDayYear,
            "yyyymmdd": yearMonthDay,
            "any_date": dayMonthYear | monthDayYear | yearMonthDay,
        }
    else:
        return {}


def getKnownFlags(digits):
    digitColumns = [pl.col(f"digit_{position}") for position in range(digits)]
    steps = getStepExpressions(digits)
    rowSteps, columnSteps = getKeypadSteps(digits)
    allSame = pl.all_horizontal([step == 0 for step in steps])
    flags = dict(
        all_same=allSame,
        ascending_run=pl.all_horizontal([step == 1 for step in steps]),
        descending_run=pl.all_horizontal([step == -1 for step in steps]),
        repeated_block=pl.lit(digits % 2 == 0)
        & pl.all_horizontal(
            [
                digitColumns[position] == digitColumns[position + digits // 2]
                for position in range(digits // 2)
            ]
        )
        & ~allSame,
        keypad_line=pl.all_horizontal(
            [
                (rowSteps[position] == rowSteps[0])
                & (columnSteps[position] == columnSteps[0])
                for position in range(digits - 1)
            ]
        )
        & ((rowSteps[0] != 0) | (columnSteps[0] != 0)),
        mirror_palindrome=pl.all_horizontal(
            [
                digitColumns[position] == digitColumns[digits - 1 - position]
                for position in range(digits // 2)
            ]
        )
        & ~allSame,
        paired_digits=pl.all_horizontal(
            [
                digitColumns[position] == digitColumns[position + 1]
                for position in range(0, digits - 1, 2)
            ]
        )
        & ~allSame,
        keypad_adjacent=pl.all_horizontal(
            [
                (rowStep.abs() <= 1) & (columnStep.abs() <= 1)
                for rowStep, columnStep in zip(rowSteps, columnSteps)
            ]
        )
        & ~allSame,
        ending_69=(pl.col("pin") % 100) == 69,
        digits_0_3_only=pl.all_horizontal([digit <= 3 for digit in digitColumns]),
        digits_0_6_only=pl.all_horizontal([digit <= 6 for digit in digitColumns]),
    )
    flags.update(getKeypadShapeFlags(digits))
    flags.update(getDateFlags(digits))
    return flags


def getIndependentExpression(digits):
    logProbabilities = []
    for position in range(digits):
        summary = pins[digits].group_by(f"digit_{position}").agg(pl.col("n").sum())
        logProbability = dict(
            zip(
                summary[f"digit_{position}"].to_list(),
                numpy.log(summary["n"].to_numpy() / summary["n"].sum()).tolist(),
            )
        )
        logProbabilities.append(
            pl.col(f"digit_{position}").replace_strict(
                logProbability, return_dtype=pl.Float64
            )
        )
    return pl.sum_horizontal(logProbabilities).exp()


def saveKnownFlags(digits):
    pins[digits] = (
        pins[digits]
        .lazy()
        .with_columns(
            independent=getIndependentExpression(digits).cast(pl.Float32),
            distinct_count=getDistinctExpression(digits).cast(pl.UInt8),
            **dict(
                (f"step_{position}", step)
                for position, step in enumerate(getStepExpressions(digits))
            ),
            **{
                f"known_{name}": expression
                for name, expression in getKnownFlags(digits).items()
            },
        )
        .collect(engine="streaming")
    )


def getRelativeEntropy(coverage, share):
    return sum(
        pl.when(first > 0).then(first * (first / second).log(2)).otherwise(0.0)
        for first, second in ((coverage, share), (1 - coverage, 1 - share))
    )


def getPatternTable(digits, prefix):
    names = [name for name in pins[digits].columns if name.startswith(prefix)]
    row = (
        pins[digits]
        .lazy()
        .select(
            [
                expression
                for name in names
                for expression in (
                    pl.col(name).sum().alias(f"{name}_size"),
                    pl.when(pl.col(name)).then(pl.col("n")).sum().alias(f"{name}_sum"),
                    pl.when(pl.col(name)).then(pl.col("n")).max().alias(f"{name}_max"),
                    pl.when(pl.col(name))
                    .then(pl.col("independent").cast(pl.Float64))
                    .sum()
                    .alias(f"{name}_expected"),
                )
            ]
        )
        .collect(engine="streaming")
        .row(0)
    )
    total = pins[digits]["n"].sum()
    return (
        pl.DataFrame(
            dict(
                pattern=names,
                size=row[0::4],
                occurrences=row[1::4],
                maximum=row[2::4],
                expected=row[3::4],
            )
        )
        .filter(pl.col("size") > 1)
        .with_columns(coverage=pl.col("occurrences") / total)
        .with_columns(
            enrichment=pl.col("coverage") / (pl.col("size") / 10**digits),
            enrichment_independent=pl.col("coverage") / pl.col("expected"),
            enrichment_without_top=(pl.col("occurrences") - pl.col("maximum"))
            / total
            / ((pl.col("size") - 1) / 10**digits),
        )
        .with_columns(
            bits=getRelativeEntropy(pl.col("coverage"), pl.col("size") / 10**digits)
        )
        .sort("bits", descending=True)
    )


def showPatternBars(digits, name, prefix, table):
    ordered = table.sort("enrichment")
    positions = numpy.arange(ordered.height)
    plt.figure(figsize=(10, max(4, 0.7 * ordered.height)))
    plt.barh(
        positions - 0.27,
        ordered["enrichment"].to_numpy(),
        height=0.26,
        label="enrichment against uniform",
    )
    plt.barh(
        positions,
        ordered["enrichment_independent"].to_numpy(),
        height=0.26,
        label="enrichment against independent digits",
    )
    plt.barh(
        positions + 0.27,
        ordered["enrichment_without_top"].to_numpy(),
        height=0.26,
        label="enrichment without top PIN",
    )
    plt.axvline(1.0, color="black", linestyle="--")
    plt.xscale("log")
    plt.yticks(
        positions, [pattern.removeprefix(prefix) for pattern in ordered["pattern"]]
    )
    plt.legend()
    plt.title(f"Pattern Enrichment of {digits}-digits PIN numbers ({name})")

    plt.xlabel("enrichment (log scale)")

    plt.tight_layout()
    plt.savefig(f"attachments/v2_{name}_bars_{digits}.png", dpi=300)
    plt.show()


def showKnownPatterns(digits):
    table = getPatternTable(digits, "known_")
    saveText(digits, "known_patterns", table)
    showPatternBars(digits, "known_patterns", "known_", table)


def showBerryCheck(digits):
    if digits == 4:
        saveText(
            digits,
            "berry_check",
            pins[digits]
            .lazy()
            .select(
                share_1234=pl.col("probability").filter(pl.col("pin") == 1234).first(),
                share_1111=pl.col("probability").filter(pl.col("pin") == 1111).first(),
                share_0000=pl.col("probability").filter(pl.col("pin") == 0).first(),
                top_20_share=pl.col("probability").head(20).sum(),
                count_1234=pl.col("n").filter(pl.col("pin") == 1234).first(),
                bottom_4200_total=pl.col("n").tail(4200).sum(),
                years_1900s_in_top_20_percent=(
                    pl.col("rank").filter(
                        (pl.col("pin") >= 1900) & (pl.col("pin") <= 1999)
                    )
                    <= 2000
                ).mean(),
                repeated_pairs_excluding_all_same=pl.col("probability")
                .filter(pl.col("known_repeated_block"))
                .sum(),
                repeated_pairs_including_all_same=pl.col("probability")
                .filter(pl.col("known_repeated_block") | pl.col("known_all_same"))
                .sum(),
            )
            .collect(engine="streaming"),
        )
    elif digits == 5:
        saveText(
            digits,
            "berry_check",
            pins[digits]
            .lazy()
            .select(
                share_12345=pl.col("probability").filter(pl.col("pin") == 12345).first(),
                share_11111=pl.col("probability").filter(pl.col("pin") == 11111).first(),
                share_00000=pl.col("probability").filter(pl.col("pin") == 0).first(),
                top_20_share=pl.col("probability").head(20).sum(),
                count_12345=pl.col("n").filter(pl.col("pin") == 12345).first(),
            )
            .collect(engine="streaming"),
        )
    else:
        pass


def showZipfFit(digits):
    positive = (
        pins[digits]
        .lazy()
        .filter(pl.col("n") >= 10)
        .select("rank", "n")
        .collect(engine="streaming")
    )
    ranks = numpy.unique(numpy.geomspace(1, positive.height, 2000).astype(numpy.int64))
    logRanks = numpy.log10(ranks)
    logCounts = numpy.log10(positive["n"][ranks - 1].to_numpy())
    slope, intercept = numpy.polyfit(logRanks, logCounts, 1)
    saveText(
        digits,
        "zipf_fit",
        f"slope {slope} intercept {intercept} correlation {numpy.corrcoef(logRanks, logCounts)[0, 1]}",
    )

In [4]:
for digits in range(3, 9):
    if digits == 7:
        continue
    else:
        saveKnownFlags(digits)
        showKnownPatterns(digits)
        showBerryCheck(digits)
        showZipfFit(digits)

known_patterns 3
shape: (10, 10)
┌─────────────────────────┬──────┬─────────────┬─────────┬──────────┬──────────┬────────────┬────────────────────────┬────────────────────────┬──────────┐
│ pattern                 ┆ size ┆ occurrences ┆ maximum ┆ expected ┆ coverage ┆ enrichment ┆ enrichment_independent ┆ enrichment_without_top ┆ bits     │
│ ---                     ┆ ---  ┆ ---         ┆ ---     ┆ ---      ┆ ---      ┆ ---        ┆ ---                    ┆ ---                    ┆ ---      │
│ str                     ┆ i64  ┆ i64         ┆ i64     ┆ f64      ┆ f64      ┆ f64        ┆ f64                    ┆ f64                    ┆ f64      │
╞═════════════════════════╪══════╪═════════════╪═════════╪══════════╪══════════╪════════════╪════════════════════════╪════════════════════════╪══════════╡
│ known_ascending_run     ┆ 8    ┆ 1867953     ┆ 1783558 ┆ 0.059402 ┆ 0.309577 ┆ 38.697133  ┆ 5.21154                ┆ 1.99812                ┆ 1.271763 │
│ known_keypad_line       ┆ 18   ┆ 19

zipf_fit 3
slope -0.6332130606519715 intercept 5.1134348496296615 correlation -0.9772581313949434
known_patterns 4
shape: (22, 10)
┌─────────────────────────┬──────┬─────────────┬─────────┬──────────┬──────────┬────────────┬────────────────────────┬────────────────────────┬──────────┐
│ pattern                 ┆ size ┆ occurrences ┆ maximum ┆ expected ┆ coverage ┆ enrichment ┆ enrichment_independent ┆ enrichment_without_top ┆ bits     │
│ ---                     ┆ ---  ┆ ---         ┆ ---     ┆ ---      ┆ ---      ┆ ---        ┆ ---                    ┆ ---                    ┆ ---      │
│ str                     ┆ i64  ┆ i64         ┆ i64     ┆ f64      ┆ f64      ┆ f64        ┆ f64                    ┆ f64                    ┆ f64      │
╞═════════════════════════╪══════╪═════════════╪═════════╪══════════╪══════════╪════════════╪════════════════════════╪════════════════════════╪══════════╡
│ known_ascending_run     ┆ 7    ┆ 2757662     ┆ 2633239 ┆ 0.002071 ┆ 0.094346 ┆ 134.779697 ┆ 

berry_check 4
shape: (1, 9)
┌────────────┬────────────┬────────────┬──────────────┬────────────┬───────────────────┬───────────────────────────────┬───────────────────────────────────┬───────────────────────────────────┐
│ share_1234 ┆ share_1111 ┆ share_0000 ┆ top_20_share ┆ count_1234 ┆ bottom_4200_total ┆ years_1900s_in_top_20_percent ┆ repeated_pairs_excluding_all_same ┆ repeated_pairs_including_all_same │
│ ---        ┆ ---        ┆ ---        ┆ ---          ┆ ---        ┆ ---               ┆ ---                           ┆ ---                               ┆ ---                               │
│ f64        ┆ f64        ┆ f64        ┆ f64          ┆ i64        ┆ i64               ┆ f64                           ┆ f64                               ┆ f64                               │
╞════════════╪════════════╪════════════╪══════════════╪════════════╪═══════════════════╪═══════════════════════════════╪═══════════════════════════════════╪═══════════════════════════════════╡
│ 0.090

berry_check 5
shape: (1, 5)
┌─────────────┬─────────────┬─────────────┬──────────────┬─────────────┐
│ share_12345 ┆ share_11111 ┆ share_00000 ┆ top_20_share ┆ count_12345 │
│ ---         ┆ ---         ┆ ---         ┆ ---          ┆ ---         │
│ f64         ┆ f64         ┆ f64         ┆ f64          ┆ i64         │
╞═════════════╪═════════════╪═════════════╪══════════════╪═════════════╡
│ 0.162729    ┆ 0.018677    ┆ 0.007156    ┆ 0.234893     ┆ 3508324     │
└─────────────┴─────────────┴─────────────┴──────────────┴─────────────┘
zipf_fit 5
slope -0.5255789140199242 intercept 4.487221792013687 correlation -0.9576600011161303
known_patterns 6
shape: (14, 10)
┌─────────────────────────┬────────┬─────────────┬──────────┬──────────┬──────────┬─────────────┬────────────────────────┬────────────────────────┬──────────┐
│ pattern                 ┆ size   ┆ occurrences ┆ maximum  ┆ expected ┆ coverage ┆ enrichment  ┆ enrichment_independent ┆ enrichment_without_top ┆ bits     │
│ ---        

zipf_fit 6
slope -0.8003907197537926 intercept 6.535834040552754 correlation -0.9874280396000616


known_patterns 8
shape: (14, 10)
┌─────────────────────────┬─────────┬─────────────┬──────────┬───────────┬──────────┬──────────────┬────────────────────────┬────────────────────────┬──────────┐
│ pattern                 ┆ size    ┆ occurrences ┆ maximum  ┆ expected  ┆ coverage ┆ enrichment   ┆ enrichment_independent ┆ enrichment_without_top ┆ bits     │
│ ---                     ┆ ---     ┆ ---         ┆ ---      ┆ ---       ┆ ---      ┆ ---          ┆ ---                    ┆ ---                    ┆ ---      │
│ str                     ┆ i64     ┆ i64         ┆ i64      ┆ f64       ┆ f64      ┆ f64          ┆ f64                    ┆ f64                    ┆ f64      │
╞═════════════════════════╪═════════╪═════════════╪══════════╪═══════════╪══════════╪══════════════╪════════════════════════╪════════════════════════╪══════════╡
│ known_any_date          ┆ 190800  ┆ 231208530   ┆ 226555   ┆ 0.028523  ┆ 0.291253 ┆ 152.648342   ┆ 10.211276              ┆ 152.499565             ┆ 1.7627

zipf_fit 8
slope -0.8031607032319552 intercept 6.833321290900752 correlation -0.9820196792868925


In [5]:
def getAscendingOrFlat(digits):
    return pl.all_horizontal(
        [pl.col(f"step_{position}") >= 0 for position in range(digits - 1)]
    ) & ~pl.col("known_all_same")


def getKnownStructure():
    return pl.any_horizontal(
        [
            pl.col(name)
            for name in [
                "known_all_same",
                "known_repeated_block",
                "known_paired_digits",
                "known_mirror_palindrome",
                "known_ascending_run",
                "known_descending_run",
            ]
        ]
    )


def getKnownDates(digits):
    dateNames = dict(
        [
            (3, []),
            (4, ["known_any_date", "known_year_1900_2029"]),
            (5, []),
            (6, ["known_any_date"]),
            (8, ["known_any_date"]),
        ]
    )[digits]
    return pl.any_horizontal([pl.lit(False)] + [pl.col(name) for name in dateNames])


def getKeypadStrokes(digits):
    rowSteps, columnSteps = getKeypadSteps(digits)
    return (
        pl.all_horizontal(
            [
                (rowSteps[start] == rowSteps[start + 1])
                & (columnSteps[start] == columnSteps[start + 1])
                & ((rowSteps[start] != 0) | (columnSteps[start] != 0))
                for start in range(0, digits - 2, 3)
            ]
        )
        & ~getKnownStructure()
    )


def getCountingBlocks(digits):
    blocks = [
        getNumber(digits, 2 * position, 2).cast(pl.Int64)
        for position in range(digits // 2)
    ]
    steps = [
        blocks[position + 1] - blocks[position] for position in range(len(blocks) - 1)
    ]
    return (
        pl.all_horizontal([step == steps[0] for step in steps])
        & (steps[0] != 0)
        & ~getKnownStructure()
    )


def getWrappedRun(digits):
    steps = [pl.col(f"step_{position}") for position in range(digits - 1)]
    wrapped = [(step + 10) % 10 for step in steps]
    return (
        pl.all_horizontal([value == wrapped[0] for value in wrapped])
        & (wrapped[0] != 0)
        & ~pl.all_horizontal([step == steps[0] for step in steps])
    )


def getRoundEnding(digits):
    return (
        (pl.col(f"digit_{digits - 1}") == 0)
        & (pl.col(f"digit_{digits - 2}") == 0)
        & ~pl.col("known_all_same")
    )


def getNewFlags(digits):
    steps = [pl.col(f"step_{position}") for position in range(digits - 1)]
    flags = dict(
        constant_step=pl.all_horizontal([step == steps[0] for step in steps])
        & (steps[0].abs() >= 2),
        ascending_or_flat=getAscendingOrFlat(digits),
        leading_zero=pl.col("digit_0") == 0,
        wrapped_run=getWrappedRun(digits),
        round_ending=getRoundEnding(digits),
        leading_one=(pl.col("digit_0") == 1)
        & ~getKnownStructure()
        & ~getKnownDates(digits),
        high_majority=pl.sum_horizontal(
            [pl.col(f"digit_{position}") >= 7 for position in range(digits)]
        )
        > digits // 2,
    )
    if digits == 8:
        flags["phone_style_prefix"] = getNumber(digits, 0, 2).is_in([9, 13, 15, 18, 19])
    else:
        pass
    if digits == 6:
        flags["keypad_strokes"] = getKeypadStrokes(digits)
    else:
        pass
    if digits in (6, 8):
        flags["counting_blocks"] = getCountingBlocks(digits)
    else:
        pass
    flags.update(
        dict(
            (f"distinct_{count}", pl.col("distinct_count") == count)
            for count in range(2, digits + 1)
        )
    )
    return flags


def saveNewFlags(digits):
    structuralNames = [
        "known_all_same",
        "known_ascending_run",
        "known_descending_run",
        "known_repeated_block",
        "known_keypad_line",
        "known_mirror_palindrome",
        "known_paired_digits",
        "known_keypad_adjacent",
    ]
    dateNames = dict(
        [
            (3, []),
            (4, ["known_any_date", "known_year_1900_2029"]),
            (5, []),
            (6, ["known_any_date"]),
            (8, ["known_any_date"]),
        ]
    )[digits]
    structural = pl.any_horizontal(
        [pl.col(name) for name in structuralNames]
        + [pl.col("distinct_count") == 2, getAscendingOrFlat(digits)]
    )
    dated = pl.any_horizontal([pl.lit(False)] + [pl.col(name) for name in dateNames])
    pins[digits] = (
        pins[digits]
        .lazy()
        .with_columns(
            structural=structural,
            dated=dated,
            residual=~(structural | dated),
            high_digits=pl.sum_horizontal(
                [pl.col(f"digit_{position}") >= 7 for position in range(digits)]
            ).cast(pl.UInt8),
            zero_digits=pl.sum_horizontal(
                [pl.col(f"digit_{position}") == 0 for position in range(digits)]
            ).cast(pl.UInt8),
            double_zero=(pl.col(f"digit_{digits - 1}") == 0)
            & (pl.col(f"digit_{digits - 2}") == 0),
            digit_sum=pl.sum_horizontal(
                [
                    pl.col(f"digit_{position}").cast(pl.Int16)
                    for position in range(digits)
                ]
            ),
            step_total=pl.sum_horizontal(
                [
                    pl.col(f"step_{position}").abs().cast(pl.Int16)
                    for position in range(digits - 1)
                ]
            ),
            **dict(
                (f"new_{name}", expression)
                for name, expression in getNewFlags(digits).items()
            ),
        )
        .collect(engine="streaming")
    )


def showNewPatterns(digits):
    table = getPatternTable(digits, "new_")
    saveText(digits, "new_patterns", table)
    showPatternBars(digits, "new_patterns", "new_", table)


def showResidualHeatmap(digits, table):
    grid = numpy.full((10, digits), numpy.nan)
    for position in range(digits):
        rows = table.filter(pl.col("feature") == f"digit_{position}")
        grid[rows["value"].to_numpy(), position] = rows["enrichment"].to_numpy()
    logGrid = numpy.log2(grid)
    limit = numpy.nanmax(numpy.abs(logGrid))
    plt.figure(figsize=(10, 6))
    plt.imshow(logGrid, cmap="coolwarm", vmin=-limit, vmax=limit, aspect="auto")
    plt.colorbar(label="log2(enrichment)")
    plt.xticks(range(digits), range(1, digits + 1))
    plt.yticks(range(10))
    plt.title(f"Residual Digit Bias of {digits}-digits PIN numbers")

    plt.xlabel("position")

    plt.ylabel("digit")
    plt.savefig(f"attachments/v2_residual_heatmap_{digits}.png", dpi=300)
    plt.show()


def showResidualBias(digits):
    featureNames = (
        [f"digit_{position}" for position in range(digits)]
        + [f"step_{position}" for position in range(digits - 1)]
        + ["high_digits", "zero_digits", "double_zero"]
    )
    residual = (
        pins[digits]
        .lazy()
        .filter(pl.col("residual"))
        .select(["n"] + featureNames)
        .collect(engine="streaming")
    )
    meanCount = residual["n"].mean()
    table = pl.concat(
        [
            residual.group_by(name)
            .agg(
                (pl.col("n").mean() / meanCount).alias("enrichment"),
                pl.len().alias("size"),
            )
            .select(
                pl.lit(name).alias("feature"),
                pl.col(name).cast(pl.Int64).alias("value"),
                "enrichment",
                "size",
            )
            .sort("value")
            for name in featureNames
        ]
    )
    saveText(digits, "residual_bias", table)
    showResidualHeatmap(digits, table)


def getPatternBits(support, share):
    if support <= 0 or support >= 1 or share <= 0 or share >= 1:
        return 0.0
    else:
        return sum(
            p * numpy.log2(p / q)
            for p, q in ((share, support), (1 - share, 1 - support))
        )


def getRobustBits(count, weight, maximum, height, totalWeight):
    if count < 2 or weight <= maximum:
        return 0.0
    else:
        return getPatternBits(
            (count - 1) / (height - 1), (weight - maximum) / (totalWeight - maximum)
        )


sizePenalty = 0.003


def getFitness(tree, statistics):
    if statistics[0] > 0.5:
        return -1.0
    else:
        return statistics[3] - sizePenalty * getTreeSize(tree)


def getDigits(value):
    return (
        numpy.rint(value).astype(numpy.int64)[:, None] // 11 ** numpy.arange(10)
    ) % 11


def getLength(value):
    return numpy.maximum(
        (numpy.rint(value)[:, None] >= 11.0 ** numpy.arange(10)).sum(axis=1), 1
    )


def getValue(sequence):
    return (sequence * 11 ** numpy.arange(10)).sum(axis=1).astype(numpy.float64)


def getSuccessor(value):
    sequence = getDigits(value)
    return getValue(
        numpy.where(
            numpy.arange(10) < getLength(value)[:, None],
            numpy.where(sequence == 10, 1, sequence + 1),
            0,
        )
    )


def getReverse(value):
    length = getLength(value)[:, None]
    return getValue(
        numpy.where(
            numpy.arange(10) < length,
            numpy.take_along_axis(
                getDigits(value), numpy.clip(length - 1 - numpy.arange(10), 0, 9), axis=1
            ),
            0,
        )
    )


def getOrder(value):
    return getValue(
        numpy.sort(
            numpy.where(
                numpy.arange(10) < getLength(value)[:, None], getDigits(value), 0
            ),
            axis=1,
        )[:, ::-1]
    )


def getLag(value):
    return numpy.rint(value) % 11.0 ** (getLength(value) - 1)


def getLead(value):
    return numpy.rint(value) // 11


def getAt(value, position):
    index = getLength(value) - 1 - numpy.rint(position).astype(numpy.int64)
    return numpy.where(
        index >= 0,
        numpy.maximum(
            numpy.take_along_axis(
                getDigits(value), numpy.clip(index, 0, 9)[:, None], axis=1
            )[:, 0]
            - 1,
            0,
        ),
        0,
    ).astype(numpy.float64)


sequenceOperators = dict(
    logical_and=lambda left, right: ((left > 0) & (right > 0)).astype(numpy.float64),

    logical_or=lambda left, right: ((left > 0) | (right > 0)).astype(numpy.float64),

    logical_not=lambda value: (value <= 0).astype(numpy.float64),

    greater=lambda left, right: (left > right).astype(numpy.float64),

    equal=lambda left, right: (left == right).astype(numpy.float64),

    at=getAt,

    succ=getSuccessor,

    flip=getReverse,

    order=getOrder,

    lag=getLag,

    lead=getLead,
)


searchChunk = 1 << 19
leafNames = ["x"] + [f"k{value}" for value in range(10)]
unaryNames = ["logical_not", "succ", "flip", "order", "lag", "lead"]
binaryNames = ["logical_and", "logical_or", "greater", "equal", "at"]
searchBudget = dict(
    [(3, (1000, 100)), (4, (500, 60)), (5, (120, 40)), (6, (20, 10)), (8, (2, 1))]
)
foundTrees = {}


def getEncoded(digits, start, size):
    pinValues = (
        pins[digits]["pin"].slice(start, size).to_numpy().astype(numpy.int64)
    )
    return sum(
        ((pinValues // 10 ** (digits - 1 - position)) % 10 + 1)
        * 11 ** (digits - 1 - position)
        for position in range(digits)
    ).astype(numpy.float64)


def getCounts(digits, start, size):
    return pins[digits]["n"].slice(start, size).cast(pl.Float64).to_numpy()


def getRandomTree(generator, size):
    if size == 1:
        return leafNames[0 if generator.random() < 0.5 else generator.integers(1, 11)]
    elif size == 2 or generator.random() < 0.4:
        return (
            unaryNames[generator.integers(len(unaryNames))],
            getRandomTree(generator, size - 1),
        )
    else:
        leftSize = int(generator.integers(1, size - 1))
        return (
            binaryNames[generator.integers(len(binaryNames))],
            getRandomTree(generator, leftSize),
            getRandomTree(generator, size - 1 - leftSize),
        )


def hasInput(tree):
    if isinstance(tree, str):
        return tree == "x"
    else:
        return any(hasInput(child) for child in tree[1:])


def getTreeSize(tree):
    if isinstance(tree, str):
        return 1
    else:
        return 1 + sum(getTreeSize(child) for child in tree[1:])


def getText(tree):
    if isinstance(tree, str):
        return tree
    else:
        return f"{tree[0]}({', '.join(getText(child) for child in tree[1:])})"


def getPaths(tree, path=()):
    paths = [path]
    if isinstance(tree, str):
        pass
    else:
        for position, child in enumerate(tree[1:], start=1):
            paths += getPaths(child, path + (position,))
    return paths


def getAtPath(tree, path):
    for position in path:
        tree = tree[position]
    return tree


def setAtPath(tree, path, value):
    if path:
        children = list(tree)
        children[path[0]] = setAtPath(tree[path[0]], path[1:], value)
        return tuple(children)
    else:
        return value


def getMutation(generator, tree, maxSize):
    size = getTreeSize(tree)
    kind = generator.integers(4)
    if kind == 0:
        paths = getPaths(tree)
        path = paths[generator.integers(len(paths))]
        room = getTreeSize(getAtPath(tree, path)) + maxSize - size
        return setAtPath(
            tree, path, getRandomTree(generator, int(generator.integers(1, room + 1)))
        )
    elif kind == 1 and size < maxSize:
        return (unaryNames[generator.integers(len(unaryNames))], tree)
    elif kind == 2 and size < maxSize - 1:
        sibling = getRandomTree(generator, int(generator.integers(1, maxSize - size)))
        pair = (tree, sibling) if generator.random() < 0.5 else (sibling, tree)
        return (binaryNames[generator.integers(len(binaryNames))], *pair)
    else:
        return getRandomTree(generator, int(generator.integers(1, maxSize + 1)))


def evaluateTree(tree, values, cache):
    if tree not in cache:
        if tree == "x":
            cache[tree] = values
        elif isinstance(tree, str):
            cache[tree] = numpy.full(values.size, float(tree[1:]))
        else:
            cache[tree] = sequenceOperators[tree[0]](
                *[evaluateTree(child, values, cache) for child in tree[1:]]
            )
    else:
        pass
    return cache[tree]


def getRuleStatistics(digits, trees):
    hashers = [hashlib.blake2b() for _ in trees]
    memberCounts = [0] * len(trees)
    memberWeights = [0.0] * len(trees)
    memberMaxima = [0.0] * len(trees)
    totalWeight = 0.0
    height = pins[digits].height
    if trees:
        for start in range(0, height, searchChunk):
            values = getEncoded(digits, start, searchChunk)
            counts = getCounts(digits, start, searchChunk)
            cache = {}
            totalWeight += counts.sum()
            for index, tree in enumerate(trees):
                member = evaluateTree(tree, values, cache) > 0
                hashers[index].update(numpy.packbits(member).tobytes())
                memberCounts[index] += int(member.sum())
                memberWeights[index] += float(counts[member].sum())
                if member.any():
                    memberMaxima[index] = max(
                        memberMaxima[index], float(counts[member].max())
                    )
                else:
                    pass
    else:
        pass
    return [
        (
            count / height,
            weight / totalWeight,
            hasher.digest(),
            getRobustBits(count, weight, maximum, height, totalWeight),
        )
        for count, weight, maximum, hasher in zip(
            memberCounts, memberWeights, memberMaxima, hashers
        )
    ]


def getSearchScores(digits, maxSize):
    population, generations = searchBudget[digits]
    seedLimit = max(2, population // 4)
    generator = numpy.random.default_rng(digits)
    current = []
    for found in reversed(list(foundTrees.values())):
        for tree in found:
            if len(current) < seedLimit and tree not in current:
                current.append(tree)
            else:
                pass
    for _ in range(population * 20):
        if len(current) < population:
            tree = getRandomTree(generator, int(generator.integers(3, maxSize + 1)))
            if hasInput(tree) and tree not in current:
                current.append(tree)
            else:
                pass
        else:
            pass
    scores = {}
    for generation in range(generations):
        fresh = [tree for tree in current if tree not in scores]
        scores.update(zip(fresh, getRuleStatistics(digits, fresh)))
        if generation < generations - 1:
            ranked = sorted(scores, key=lambda tree: -getFitness(tree, scores[tree]))
            elite = ranked[: max(2, population // 4)]
            current = []
            for _ in range(population * 20):
                if len(current) < population:
                    child = getMutation(
                        generator, elite[int(generator.integers(len(elite)))], maxSize
                    )
                    if hasInput(child) and child not in scores and child not in current:
                        current.append(child)
                    else:
                        pass
                else:
                    pass
        else:
            pass
    return scores


def showBooleanPatterns(digits, maxSize=7):
    start = time.perf_counter()
    scores = getSearchScores(digits, maxSize)
    rows, kept, seen = [], [], set()
    for tree in sorted(scores, key=lambda tree: -getFitness(tree, scores[tree])):
        support, share, key, robust = scores[tree]
        fitness = getFitness(tree, scores[tree])
        if fitness > 0 and key not in seen:
            seen.add(key)
            kept.append(tree)
            rows.append(
                dict(
                    score=float(fitness),
                    robust_bits=float(robust),
                    bits=float(getPatternBits(support, share)),
                    size=getTreeSize(tree),
                    support=float(support),
                    occurrence_share=float(share),
                    enrichment=float(share / support),
                    rule=getText(tree),
                )
            )
        else:
            pass
    foundTrees[digits] = kept[:10]
    if rows:
        saveText(
            digits,
            "boolean_patterns",
            pl.DataFrame(rows)
            .with_columns(pl.col(pl.Float64).round(9))
            .sort("score", descending=True),
        )
    else:
        saveText(digits, "boolean_patterns", "none")
    print(f"Searching used {round(time.perf_counter() - start, 2)} seconds.")

In [6]:
for digits in range(3, 9):
    if digits == 7:
        continue
    else:
        saveNewFlags(digits)
        showNewPatterns(digits)
        showResidualBias(digits)
        showBooleanPatterns(digits)

new_patterns 3
shape: (9, 10)
┌───────────────────────┬──────┬─────────────┬─────────┬──────────┬──────────┬────────────┬────────────────────────┬────────────────────────┬───────────┐
│ pattern               ┆ size ┆ occurrences ┆ maximum ┆ expected ┆ coverage ┆ enrichment ┆ enrichment_independent ┆ enrichment_without_top ┆ bits      │
│ ---                   ┆ ---  ┆ ---         ┆ ---     ┆ ---      ┆ ---      ┆ ---        ┆ ---                    ┆ ---                    ┆ ---       │
│ str                   ┆ i64  ┆ i64         ┆ i64     ┆ f64      ┆ f64      ┆ f64        ┆ f64                    ┆ f64                    ┆ f64       │
╞═══════════════════════╪══════╪═════════════╪═════════╪══════════╪══════════╪════════════╪════════════════════════╪════════════════════════╪═══════════╡
│ new_ascending_or_flat ┆ 210  ┆ 2573259     ┆ 1783558 ┆ 0.307902 ┆ 0.426468 ┆ 2.030799   ┆ 1.385075               ┆ 0.626209               ┆ 0.170911  │
│ new_high_majority     ┆ 216  ┆ 678942      ┆

residual_bias 3
shape: (73, 4)
┌─────────────┬───────┬────────────┬──────┐
│ feature     ┆ value ┆ enrichment ┆ size │
│ ---         ┆ ---   ┆ ---        ┆ ---  │
│ str         ┆ i64   ┆ f64        ┆ u32  │
╞═════════════╪═══════╪════════════╪══════╡
│ digit_0     ┆ 0     ┆ 0.960723   ┆ 27   │
│ digit_0     ┆ 1     ┆ 2.217908   ┆ 40   │
│ digit_0     ┆ 2     ┆ 1.631032   ┆ 42   │
│ digit_0     ┆ 3     ┆ 0.93883    ┆ 48   │
│ digit_0     ┆ 4     ┆ 0.87437    ┆ 46   │
│ digit_0     ┆ 5     ┆ 0.827128   ┆ 42   │
│ digit_0     ┆ 6     ┆ 0.738424   ┆ 49   │
│ digit_0     ┆ 7     ┆ 0.693908   ┆ 53   │
│ digit_0     ┆ 8     ┆ 0.72941    ┆ 48   │
│ digit_0     ┆ 9     ┆ 0.700834   ┆ 54   │
│ digit_1     ┆ 0     ┆ 1.124419   ┆ 66   │
│ digit_1     ┆ 1     ┆ 1.010675   ┆ 57   │
│ digit_1     ┆ 2     ┆ 1.073423   ┆ 42   │
│ digit_1     ┆ 3     ┆ 0.915469   ┆ 49   │
│ digit_1     ┆ 4     ┆ 0.924049   ┆ 37   │
│ digit_1     ┆ 5     ┆ 1.449244   ┆ 12   │
│ digit_1     ┆ 6     ┆ 0.93353    ┆ 39   │
│

boolean_patterns 3
shape: (119, 8)
┌───────────┬─────────────┬──────────┬──────┬─────────┬──────────────────┬────────────┬───────────────────────────────────────────────┐
│ score     ┆ robust_bits ┆ bits     ┆ size ┆ support ┆ occurrence_share ┆ enrichment ┆ rule                                          │
│ ---       ┆ ---         ┆ ---      ┆ ---  ┆ ---     ┆ ---              ┆ ---        ┆ ---                                           │
│ f64       ┆ f64         ┆ f64      ┆ i64  ┆ f64     ┆ f64              ┆ f64        ┆ str                                           │
╞═══════════╪═════════════╪══════════╪══════╪═════════╪══════════════════╪════════════╪═══════════════════════════════════════════════╡
│ 0.174317  ┆ 0.189317    ┆ 0.152005 ┆ 5    ┆ 0.5     ┆ 0.274605         ┆ 0.54921    ┆ greater(at(x, k0), k4)                        │
│ 0.162909  ┆ 0.183909    ┆ 0.176602 ┆ 7    ┆ 0.464   ┆ 0.22546          ┆ 0.485905   ┆ greater(x, succ(succ(order(succ(x)))))        │
│ 0.161531  ┆

residual_bias 4
shape: (107, 4)
┌─────────────┬───────┬────────────┬──────┐
│ feature     ┆ value ┆ enrichment ┆ size │
│ ---         ┆ ---   ┆ ---        ┆ ---  │
│ str         ┆ i64   ┆ f64        ┆ u32  │
╞═════════════╪═══════╪════════════╪══════╡
│ digit_0     ┆ 0     ┆ 0.555092   ┆ 417  │
│ digit_0     ┆ 1     ┆ 1.878953   ┆ 507  │
│ digit_0     ┆ 2     ┆ 1.299724   ┆ 588  │
│ digit_0     ┆ 3     ┆ 1.00695    ┆ 749  │
│ digit_0     ┆ 4     ┆ 0.981018   ┆ 732  │
│ digit_0     ┆ 5     ┆ 0.978136   ┆ 669  │
│ digit_0     ┆ 6     ┆ 0.868027   ┆ 742  │
│ digit_0     ┆ 7     ┆ 0.895135   ┆ 781  │
│ digit_0     ┆ 8     ┆ 0.870318   ┆ 727  │
│ digit_0     ┆ 9     ┆ 0.822124   ┆ 781  │
│ digit_1     ┆ 0     ┆ 1.003053   ┆ 776  │
│ digit_1     ┆ 1     ┆ 1.036743   ┆ 758  │
│ digit_1     ┆ 2     ┆ 1.030857   ┆ 654  │
│ digit_1     ┆ 3     ┆ 1.137276   ┆ 725  │
│ digit_1     ┆ 4     ┆ 1.011119   ┆ 640  │
│ digit_1     ┆ 5     ┆ 1.067688   ┆ 450  │
│ digit_1     ┆ 6     ┆ 0.95418    ┆ 656  │


boolean_patterns 4
shape: (45, 8)
┌──────────┬─────────────┬───────────┬──────┬─────────┬──────────────────┬────────────┬──────────────────────────────────────────────────┐
│ score    ┆ robust_bits ┆ bits      ┆ size ┆ support ┆ occurrence_share ┆ enrichment ┆ rule                                             │
│ ---      ┆ ---         ┆ ---       ┆ ---  ┆ ---     ┆ ---              ┆ ---        ┆ ---                                              │
│ f64      ┆ f64         ┆ f64       ┆ i64  ┆ f64     ┆ f64              ┆ f64        ┆ str                                              │
╞══════════╪═════════════╪═══════════╪══════╪═════════╪══════════════════╪════════════╪══════════════════════════════════════════════════╡
│ 0.166206 ┆ 0.181206    ┆ 0.312199  ┆ 5    ┆ 0.1     ┆ 0.343256         ┆ 3.432562   ┆ equal(k1, at(x, k0))                             │
│ 0.138537 ┆ 0.156537    ┆ 0.220105  ┆ 6    ┆ 0.3     ┆ 0.566655         ┆ 1.888849   ┆ logical_not(greater(at(x, k0), k2))         

...

residual_bias 6
shape: (169, 4)
┌─────────────┬───────┬────────────┬────────┐
│ feature     ┆ value ┆ enrichment ┆ size   │
│ ---         ┆ ---   ┆ ---        ┆ ---    │
│ str         ┆ i64   ┆ f64        ┆ u32    │
╞═════════════╪═══════╪════════════╪════════╡
│ digit_0     ┆ 0     ┆ 0.597287   ┆ 66402  │
│ digit_0     ┆ 1     ┆ 2.678038   ┆ 77009  │
│ digit_0     ┆ 2     ┆ 1.444475   ┆ 79973  │
│ digit_0     ┆ 3     ┆ 0.952962   ┆ 89099  │
│ digit_0     ┆ 4     ┆ 0.811524   ┆ 88078  │
│ digit_0     ┆ 5     ┆ 0.89259    ┆ 84938  │
│ digit_0     ┆ 6     ┆ 0.748344   ┆ 88116  │
│ digit_0     ┆ 7     ┆ 0.794132   ┆ 89534  │
│ digit_0     ┆ 8     ┆ 0.593689   ┆ 87196  │
│ digit_0     ┆ 9     ┆ 0.641637   ┆ 89514  │
│ digit_1     ┆ 0     ┆ 1.001882   ┆ 88167  │
│ digit_1     ┆ 1     ┆ 0.991666   ┆ 85894  │
│ digit_1     ┆ 2     ┆ 1.092072   ┆ 82412  │
│ digit_1     ┆ 3     ┆ 0.95813    ┆ 87327  │
│ digit_1     ┆ 4     ┆ 0.962287   ┆ 83573  │
│ digit_1     ┆ 5     ┆ 1.210322   ┆ 74932  │
│ 

boolean_patterns 6
shape: (7, 8)
┌──────────┬─────────────┬──────────┬──────┬──────────┬──────────────────┬─────────────┬─────────────────────────────────────┐
│ score    ┆ robust_bits ┆ bits     ┆ size ┆ support  ┆ occurrence_share ┆ enrichment  ┆ rule                                │
│ ---      ┆ ---         ┆ ---      ┆ ---  ┆ ---      ┆ ---              ┆ ---         ┆ ---                                 │
│ f64      ┆ f64         ┆ f64      ┆ i64  ┆ f64      ┆ f64              ┆ f64         ┆ str                                 │
╞══════════╪═════════════╪══════════╪══════╪══════════╪══════════════════╪═════════════╪═════════════════════════════════════╡
│ 0.286324 ┆ 0.301324    ┆ 0.480368 ┆ 5    ┆ 0.00001  ┆ 0.04481          ┆ 4481.030189 ┆ equal(lead(x), lag(x))              │
│ 0.226591 ┆ 0.241591    ┆ 0.233849 ┆ 5    ┆ 0.5      ┆ 0.223302         ┆ 0.446604    ┆ greater(at(x, k0), k4)              │
│ 0.221825 ┆ 0.236825    ┆ 0.448868 ┆ 5    ┆ 0.1      ┆ 0.39994          ┆ 3.9

new_patterns 8
shape: (15, 10)
┌────────────────────────┬──────────┬─────────────┬──────────┬───────────┬──────────┬─────────────┬────────────────────────┬────────────────────────┬──────────┐
│ pattern                ┆ size     ┆ occurrences ┆ maximum  ┆ expected  ┆ coverage ┆ enrichment  ┆ enrichment_independent ┆ enrichment_without_top ┆ bits     │
│ ---                    ┆ ---      ┆ ---         ┆ ---      ┆ ---       ┆ ---      ┆ ---         ┆ ---                    ┆ ---                    ┆ ---      │
│ str                    ┆ i64      ┆ i64         ┆ i64      ┆ f64       ┆ f64      ┆ f64         ┆ f64                    ┆ f64                    ┆ f64      │
╞════════════════════════╪══════════╪═════════════╪══════════╪═══════════╪══════════╪═════════════╪════════════════════════╪════════════════════════╪══════════╡
│ new_ascending_or_flat  ┆ 24300    ┆ 49942699    ┆ 39918339 ┆ 0.000443  ┆ 0.062913 ┆ 258.900175  ┆ 142.119402             ┆ 51.967863              ┆ 0.416806 │
│ n

residual_bias 8
shape: (231, 4)
┌─────────────┬───────┬────────────┬──────────┐
│ feature     ┆ value ┆ enrichment ┆ size     │
│ ---         ┆ ---   ┆ ---        ┆ ---      │
│ str         ┆ i64   ┆ f64        ┆ u32      │
╞═════════════╪═══════╪════════════╪══════════╡
│ digit_0     ┆ 0     ┆ 0.8249     ┆ 9771972  │
│ digit_0     ┆ 1     ┆ 2.038931   ┆ 9727393  │
│ digit_0     ┆ 2     ┆ 1.63466    ┆ 9661093  │
│ digit_0     ┆ 3     ┆ 1.193779   ┆ 9798456  │
│ digit_0     ┆ 4     ┆ 0.760956   ┆ 9710345  │
│ digit_0     ┆ 5     ┆ 0.536291   ┆ 9591890  │
│ digit_0     ┆ 6     ┆ 0.484893   ┆ 9710643  │
│ digit_0     ┆ 7     ┆ 0.677506   ┆ 9761856  │
│ digit_0     ┆ 8     ┆ 0.783816   ┆ 9675232  │
│ digit_0     ┆ 9     ┆ 1.059986   ┆ 9761856  │
│ digit_1     ┆ 0     ┆ 1.144791   ┆ 9838456  │
│ digit_1     ┆ 1     ┆ 1.059566   ┆ 9846789  │
│ digit_1     ┆ 2     ┆ 1.188058   ┆ 9705380  │
│ digit_1     ┆ 3     ┆ 0.958669   ┆ 9853455  │
│ digit_1     ┆ 4     ┆ 0.898392   ┆ 9697976  │
│ digit_

boolean_patterns 8
shape: (2, 8)
┌──────────┬─────────────┬──────────┬──────┬───────────┬──────────────────┬──────────────┬────────────────────────┐
│ score    ┆ robust_bits ┆ bits     ┆ size ┆ support   ┆ occurrence_share ┆ enrichment   ┆ rule                   │
│ ---      ┆ ---         ┆ ---      ┆ ---  ┆ ---       ┆ ---              ┆ ---          ┆ ---                    │
│ f64      ┆ f64         ┆ f64      ┆ i64  ┆ f64       ┆ f64              ┆ f64          ┆ str                    │
╞══════════╪═════════════╪══════════╪══════╪═══════════╪══════════════════╪══════════════╪════════════════════════╡
│ 0.214788 ┆ 0.229788    ┆ 0.226397 ┆ 5    ┆ 0.5       ┆ 0.227486         ┆ 0.454971     ┆ greater(at(x, k0), k4) │
│ 0.081387 ┆ 0.096387    ┆ 0.135935 ┆ 5    ┆ 0.0000001 ┆ 0.009045         ┆ 90450.092853 ┆ equal(lead(x), lag(x)) │
└──────────┴─────────────┴──────────┴──────┴───────────┴──────────────────┴──────────────┴────────────────────────┘
Searching used 54.72 seconds.


In [7]:
def savePolicyColumns(digits):
    minimumDistinct = dict([(3, 3), (4, 3), (5, 4), (6, 5), (8, 6)])[digits]
    yearNames = dict(
        [(3, []), (4, ["known_year_1956_2015"]), (5, []), (6, []), (8, [])]
    )[digits]
    rounded = pl.col("double_zero") | (pl.col("zero_digits") >= (digits + 1) // 2)
    blocked = pl.any_horizontal(
        [
            pl.col(name)
            for name in [
                "known_all_same",
                "known_repeated_block",
                "known_paired_digits",
                "known_mirror_palindrome",
                "known_ascending_run",
                "known_descending_run",
            ]
            + yearNames
        ]
    )
    recommendedNames = dict(
        [
            (3, []),
            (4, []),
            (5, []),
            (6, ["new_keypad_strokes", "new_counting_blocks"]),
            (8, ["new_counting_blocks", "new_phone_style_prefix"]),
        ]
    )[digits] + [
        "known_keypad_line",
        "known_digits_0_3_only",
        "new_wrapped_run",
        "new_round_ending",
    ]
    recommended = ~pl.any_horizontal(
        [pl.col(name) for name in recommendedNames]
        + [getKnownStructure(), getKnownDates(digits)]
    ) & (pl.col("distinct_count") >= minimumDistinct)
    pins[digits] = (
        pins[digits]
        .lazy()
        .with_columns(
            policy_P0=pl.lit(True),

            policy_P1=~pl.col("structural"),

            policy_P2=pl.col("residual"),

            policy_P3=pl.col("residual") & ~rounded,

            policy_P4=pl.col("residual")
            & ~rounded
            & (pl.col("distinct_count") >= minimumDistinct),

            policy_P5=pl.col("rank") > 100,

            policy_P6=~blocked,

            policy_P7=pl.col("rank") > 10**digits // 10,

            policy_P8=recommended,

            policy_P9=recommended & (pl.col("rank") > 10**digits // 100),
        )
        .collect(engine="streaming")
    )


def showPolicies(digits):
    names = [name for name in pins[digits].columns if name.startswith("policy_")]
    quantiles = (0.001, 0.01, 0.1)
    betas = (3, 6, 10, 30, 100)
    row = (
        pins[digits]
        .lazy()
        .select(
            [
                expression
                for name in names
                for expression in [
                    pl.col(name).sum().alias(f"{name}_size"),
                    pl.col("n").filter(pl.col(name)).sum().alias(f"{name}_total"),
                ]
                + [
                    (pl.col(name) & (pl.col("rank") <= round(quantile * 10**digits)))
                    .sum()
                    .alias(f"{name}_hit_{index}")
                    for index, quantile in enumerate(quantiles)
                ]
            ]
        )
        .collect(engine="streaming")
        .row(0)
    )
    allowed = [
        pins[digits]
        .lazy()
        .filter(pl.col(name))
        .select("n")
        .head(100)
        .collect(engine="streaming")["n"]
        .to_numpy()
        .cumsum()
        for name in names
    ]
    saveText(
        digits,
        "policies",
        pl.DataFrame(
            dict(
                policy=names,
                size=row[0::5],
                share=[size / 10**digits for size in row[0::5]],
                **dict(
                    (
                        f"ratio_{quantile}",
                        [
                            hit / size / quantile
                            for hit, size in zip(row[2 + index :: 5], row[0::5])
                        ],
                    )
                    for index, quantile in enumerate(quantiles)
                ),
                **dict(
                    (
                        f"lambda_{beta}",
                        [
                            cumulative[min(beta, cumulative.size) - 1] / total
                            for cumulative, total in zip(allowed, row[1::5])
                        ],
                    )
                    for beta in betas
                ),
                **dict(
                    (f"uniform_{beta}", [min(beta, size) / size for size in row[0::5]])
                    for beta in betas
                ),
            )
        ),
    )


def showPolicyCurves(digits):
    names = [name for name in pins[digits].columns if name.startswith("policy_")]
    guesses = numpy.arange(1, 101)
    rows = []
    plt.figure(figsize=(10, 6))
    for name in names:
        allowed = (
            pins[digits]
            .lazy()
            .filter(pl.col(name))
            .select("n")
            .head(100)
            .collect(engine="streaming")["n"]
            .to_numpy()
        )
        total = pins[digits].select(pl.col("n").filter(pl.col(name)).sum()).item()
        size = pins[digits][name].sum()
        rows.append(
            dict(
                policy=name,
                share=float(size / 10**digits),
                **dict(
                    (
                        f"lift_{count}",
                        float(allowed[:count].sum() / total / (min(count, size) / size)),
                    )
                    for count in (3, 10, 100)
                ),
            )
        )
        plt.loglog(guesses[: allowed.size], allowed.cumsum() / total, label=name)
    plt.loglog(
        guesses, guesses / 10**digits, color="black", linestyle="--", label="uniform"
    )
    plt.legend()
    plt.title(f"Policy Guessing Curves of {digits}-digits PIN numbers")

    plt.xlabel("guesses")

    plt.ylabel("share of occurrences covered")
    plt.savefig(f"attachments/v2_policy_curves_{digits}.png", dpi=300)
    plt.show()
    saveText(digits, "policy_lift", pl.DataFrame(rows))
    plt.figure(figsize=(10, 6))
    for row in rows:
        plt.scatter(row["share"], row["lift_3"], label=row["policy"])
    plt.yscale("log")
    plt.legend()
    plt.title(f"Policy Trade-off of {digits}-digits PIN numbers")

    plt.xlabel("share of keyspace allowed")

    plt.ylabel("attacker advantage over uniform (3 guesses)")
    plt.savefig(f"attachments/v2_policy_tradeoff_{digits}.png", dpi=300)
    plt.show()


def showHoldout(digits):
    generator = numpy.random.default_rng(digits)
    height = pins[digits].height
    allTotal = pins[digits]["n"].sum()
    rows = []
    for name in [name for name in pins[digits].columns if name.startswith("policy_")]:
        counts = (
            pins[digits]
            .lazy()
            .filter(pl.col(name))
            .select("n")
            .head(20000)
            .collect(engine="streaming")["n"]
            .to_numpy()
        )
        total = pins[digits].select(pl.col("n").filter(pl.col(name)).sum()).item()
        train = generator.binomial(counts, 0.5)
        test = counts - train
        order = numpy.argsort(-train, kind="stable")
        for count in (3, 10, 100):
            rows.append(
                dict(
                    policy=name,
                    guesses=count,
                    in_sample=float(counts[:count].sum() / total),
                    held_out=float(2 * test[order[:count]].sum() / total),
                )
            )
    for blacklist in sorted({100, 10**digits // 100, 10**digits // 10}):
        counts = pins[digits]["n"].head(min(blacklist + 20000, height)).to_numpy()
        train = generator.binomial(counts, 0.5)
        test = counts - train
        order = numpy.argsort(-train, kind="stable")
        remaining = allTotal / 2 - test[order[:blacklist]].sum()
        for count in (3, 10, 100):
            rows.append(
                dict(
                    policy=f"blacklist_{blacklist}",
                    guesses=count,
                    in_sample=float(
                        counts[blacklist : blacklist + count].sum()
                        / (allTotal - counts[:blacklist].sum())
                    ),
                    held_out=float(
                        test[order[blacklist : blacklist + count]].sum() / remaining
                    ),
                )
            )
    saveText(digits, "holdout", pl.DataFrame(rows))


def showRecommendation(digits):
    generator = numpy.random.default_rng(digits)
    candidates = generator.integers(0, 10**digits, size=1000).tolist()
    saveText(
        digits,
        "recommended_pins",
        pins[digits]
        .lazy()
        .filter(pl.col("pin").is_in(candidates) & pl.col("policy_P9"))
        .select(pl.col("pin").cast(pl.String).str.zfill(digits))
        .head(10)
        .collect(engine="streaming"),
    )


def showSpikes(digits):
    saveText(
        digits,
        "spikes",
        pins[digits]
        .lazy()
        .filter(pl.col("residual") & (pl.col("rank") <= round(0.005 * 10**digits)))
        .select(
            pl.col("pin").cast(pl.String).str.zfill(digits),
            "n",
            enrichment=pl.col("probability") * 10**digits,
        )
        .head(25)
        .collect(engine="streaming"),
    )

In [8]:
for digits in range(3, 9):
    if digits == 7:
        continue
    else:
        savePolicyColumns(digits)
        showPolicies(digits)
        showPolicyCurves(digits)
        showHoldout(digits)
        showRecommendation(digits)
        showSpikes(digits)


policies 3
shape: (10, 16)
┌───────────┬──────┬───────┬─────────────┬────────────┬───────────┬──────────┬──────────┬───────────┬───────────┬────────────┬───────────┬───────────┬────────────┬────────────┬─────────────┐
│ policy    ┆ size ┆ share ┆ ratio_0.001 ┆ ratio_0.01 ┆ ratio_0.1 ┆ lambda_3 ┆ lambda_6 ┆ lambda_10 ┆ lambda_30 ┆ lambda_100 ┆ uniform_3 ┆ uniform_6 ┆ uniform_10 ┆ uniform_30 ┆ uniform_100 │
│ ---       ┆ ---  ┆ ---   ┆ ---         ┆ ---        ┆ ---       ┆ ---      ┆ ---      ┆ ---       ┆ ---       ┆ ---        ┆ ---       ┆ ---       ┆ ---        ┆ ---        ┆ ---         │
│ str       ┆ i64  ┆ f64   ┆ f64         ┆ f64        ┆ f64       ┆ f64      ┆ f64      ┆ f64       ┆ f64       ┆ f64        ┆ f64       ┆ f64       ┆ f64        ┆ f64        ┆ f64         │
╞═══════════╪══════╪═══════╪═════════════╪════════════╪═══════════╪══════════╪══════════╪═══════════╪═══════════╪════════════╪═══════════╪═══════════╪════════════╪════════════╪═════════════╡
│ policy_P0 ┆ 1000

policy_lift 3
shape: (10, 5)
┌───────────┬───────┬────────────┬──────────┬──────────┐
│ policy    ┆ share ┆ lift_3     ┆ lift_10  ┆ lift_100 │
│ ---       ┆ ---   ┆ ---        ┆ ---      ┆ ---      │
│ str       ┆ f64   ┆ f64        ┆ f64      ┆ f64      │
╞═══════════╪═══════╪════════════╪══════════╪══════════╡
│ policy_P0 ┆ 1.0   ┆ 116.958604 ┆ 39.68548 ┆ 5.818206 │
│ policy_P1 ┆ 0.449 ┆ 5.434267   ┆ 4.757166 ┆ 2.01289  │
│ policy_P2 ┆ 0.449 ┆ 5.434267   ┆ 4.757166 ┆ 2.01289  │
│ policy_P3 ┆ 0.449 ┆ 5.434267   ┆ 4.757166 ┆ 2.01289  │
│ policy_P4 ┆ 0.449 ┆ 5.434267   ┆ 4.757166 ┆ 2.01289  │
│ policy_P5 ┆ 0.9   ┆ 2.310713   ┆ 2.213291 ┆ 1.721996 │
│ policy_P6 ┆ 0.794 ┆ 10.972294  ┆ 6.816897 ┆ 2.729969 │
│ policy_P7 ┆ 0.9   ┆ 2.310713   ┆ 2.213291 ┆ 1.721996 │
│ policy_P8 ┆ 0.632 ┆ 5.551841   ┆ 4.986019 ┆ 2.078625 │
│ policy_P9 ┆ 0.632 ┆ 5.551841   ┆ 4.986019 ┆ 2.078625 │
└───────────┴───────┴────────────┴──────────┴──────────┘


holdout 3
shape: (36, 4)
┌───────────────┬─────────┬───────────┬──────────┐
│ policy        ┆ guesses ┆ in_sample ┆ held_out │
│ ---           ┆ ---     ┆ ---       ┆ ---      │
│ str           ┆ i64     ┆ f64       ┆ f64      │
╞═══════════════╪═════════╪═══════════╪══════════╡
│ policy_P0     ┆ 3       ┆ 0.350876  ┆ 0.350924 │
│ policy_P0     ┆ 10      ┆ 0.396855  ┆ 0.396858 │
│ policy_P0     ┆ 100     ┆ 0.581821  ┆ 0.581792 │
│ policy_P1     ┆ 3       ┆ 0.036309  ┆ 0.036197 │
│ policy_P1     ┆ 10      ┆ 0.10595   ┆ 0.105524 │
│ policy_P1     ┆ 100     ┆ 0.448305  ┆ 0.44792  │
│ policy_P2     ┆ 3       ┆ 0.036309  ┆ 0.036171 │
│ policy_P2     ┆ 10      ┆ 0.10595   ┆ 0.106239 │
│ policy_P2     ┆ 100     ┆ 0.448305  ┆ 0.447478 │
│ policy_P3     ┆ 3       ┆ 0.036309  ┆ 0.036192 │
│ policy_P3     ┆ 10      ┆ 0.10595   ┆ 0.105921 │
│ policy_P3     ┆ 100     ┆ 0.448305  ┆ 0.4478   │
│ policy_P4     ┆ 3       ┆ 0.036309  ┆ 0.03621  │
│ policy_P4     ┆ 10      ┆ 0.10595   ┆ 0.105855 │
│ poli

policies 4
shape: (10, 16)
┌───────────┬───────┬────────┬─────────────┬────────────┬───────────┬──────────┬──────────┬───────────┬───────────┬────────────┬───────────┬───────────┬────────────┬────────────┬─────────────┐
│ policy    ┆ size  ┆ share  ┆ ratio_0.001 ┆ ratio_0.01 ┆ ratio_0.1 ┆ lambda_3 ┆ lambda_6 ┆ lambda_10 ┆ lambda_30 ┆ lambda_100 ┆ uniform_3 ┆ uniform_6 ┆ uniform_10 ┆ uniform_30 ┆ uniform_100 │
│ ---       ┆ ---   ┆ ---    ┆ ---         ┆ ---        ┆ ---       ┆ ---      ┆ ---      ┆ ---       ┆ ---       ┆ ---        ┆ ---       ┆ ---       ┆ ---        ┆ ---        ┆ ---         │
│ str       ┆ i64   ┆ f64    ┆ f64         ┆ f64        ┆ f64       ┆ f64      ┆ f64      ┆ f64       ┆ f64       ┆ f64        ┆ f64       ┆ f64       ┆ f64        ┆ f64        ┆ f64         │
╞═══════════╪═══════╪════════╪═════════════╪════════════╪═══════════╪══════════╪══════════╪═══════════╪═══════════╪════════════╪═══════════╪═══════════╪════════════╪════════════╪═════════════╡
│ policy

policy_lift 4
shape: (10, 5)
┌───────────┬────────┬────────────┬────────────┬───────────┐
│ policy    ┆ share  ┆ lift_3     ┆ lift_10    ┆ lift_100  │
│ ---       ┆ ---    ┆ ---        ┆ ---        ┆ ---       │
│ str       ┆ f64    ┆ f64        ┆ f64        ┆ f64       │
╞═══════════╪════════╪════════════╪════════════╪═══════════╡
│ policy_P0 ┆ 1.0    ┆ 390.218397 ┆ 140.786643 ┆ 26.633221 │
│ policy_P1 ┆ 0.7282 ┆ 45.434585  ┆ 30.58548   ┆ 13.322138 │
│ policy_P2 ┆ 0.6693 ┆ 44.579926  ┆ 17.984949  ┆ 4.497917  │
│ policy_P3 ┆ 0.6456 ┆ 41.07158   ┆ 16.637066  ┆ 4.254468  │
│ policy_P4 ┆ 0.6456 ┆ 41.07158   ┆ 16.637066  ┆ 4.254468  │
│ policy_P5 ┆ 0.99   ┆ 9.042276   ┆ 8.864323   ┆ 6.502664  │
│ policy_P6 ┆ 0.9648 ┆ 41.387441  ┆ 23.317186  ┆ 8.215881  │
│ policy_P7 ┆ 0.9    ┆ 2.162351   ┆ 2.160292   ┆ 2.103588  │
│ policy_P8 ┆ 0.8508 ┆ 45.304344  ┆ 20.116313  ┆ 5.29548   │
│ policy_P9 ┆ 0.8504 ┆ 9.777063   ┆ 7.879868   ┆ 3.975807  │
└───────────┴────────┴────────────┴────────────┴────────

...

policy_lift 6
shape: (10, 5)
┌───────────┬──────────┬──────────────┬──────────────┬─────────────┐
│ policy    ┆ share    ┆ lift_3       ┆ lift_10      ┆ lift_100    │
│ ---       ┆ ---      ┆ ---          ┆ ---          ┆ ---         │
│ str       ┆ f64      ┆ f64          ┆ f64          ┆ f64         │
╞═══════════╪══════════╪══════════════╪══════════════╪═════════════╡
│ policy_P0 ┆ 1.0      ┆ 53791.369478 ┆ 19734.186751 ┆ 2577.414198 │
│ policy_P1 ┆ 0.921255 ┆ 2694.488966  ┆ 1690.135008  ┆ 352.017628  │
│ policy_P2 ┆ 0.839859 ┆ 4880.80736   ┆ 2722.856691  ┆ 536.994081  │
│ policy_P3 ┆ 0.823263 ┆ 5125.122886  ┆ 2859.153028  ┆ 552.764215  │
│ policy_P4 ┆ 0.528262 ┆ 5356.243508  ┆ 2988.088322  ┆ 556.393295  │
│ policy_P5 ┆ 0.9999   ┆ 314.124476   ┆ 311.066496   ┆ 228.138487  │
│ policy_P6 ┆ 0.99719  ┆ 3678.826468  ┆ 2383.69309   ┆ 676.467254  │
│ policy_P7 ┆ 0.9      ┆ 3.827305     ┆ 3.827305     ┆ 3.827305    │
│ policy_P8 ┆ 0.550626 ┆ 1574.218588  ┆ 930.946282   ┆ 232.565035  │
│ pol

holdout 6
shape: (39, 4)
┌──────────────────┬─────────┬───────────┬──────────┐
│ policy           ┆ guesses ┆ in_sample ┆ held_out │
│ ---              ┆ ---     ┆ ---       ┆ ---      │
│ str              ┆ i64     ┆ f64       ┆ f64      │
╞══════════════════╪═════════╪═══════════╪══════════╡
│ policy_P0        ┆ 3       ┆ 0.161374  ┆ 0.161341 │
│ policy_P0        ┆ 10      ┆ 0.197342  ┆ 0.197308 │
│ policy_P0        ┆ 100     ┆ 0.257741  ┆ 0.257722 │
│ policy_P1        ┆ 3       ┆ 0.008774  ┆ 0.008778 │
│ policy_P1        ┆ 10      ┆ 0.018346  ┆ 0.018347 │
│ policy_P1        ┆ 100     ┆ 0.038211  ┆ 0.038222 │
│ policy_P2        ┆ 3       ┆ 0.017434  ┆ 0.017449 │
│ policy_P2        ┆ 10      ┆ 0.03242   ┆ 0.03247  │
│ policy_P2        ┆ 100     ┆ 0.063939  ┆ 0.063989 │
│ policy_P3        ┆ 3       ┆ 0.018676  ┆ 0.018673 │
│ policy_P3        ┆ 10      ┆ 0.03473   ┆ 0.034738 │
│ policy_P3        ┆ 100     ┆ 0.067143  ┆ 0.067144 │
│ policy_P4        ┆ 3       ┆ 0.030418  ┆ 0.030399 │
│ p

policies 8
shape: (10, 16)
┌───────────┬───────────┬──────────┬─────────────┬────────────┬───────────┬───────────┬──────────┬───────────┬───────────┬────────────┬───────────┬───────────┬────────────┬────────────┬─────────────┐
│ policy    ┆ size      ┆ share    ┆ ratio_0.001 ┆ ratio_0.01 ┆ ratio_0.1 ┆ lambda_3  ┆ lambda_6 ┆ lambda_10 ┆ lambda_30 ┆ lambda_100 ┆ uniform_3 ┆ uniform_6 ┆ uniform_10 ┆ uniform_30 ┆ uniform_100 │
│ ---       ┆ ---       ┆ ---      ┆ ---         ┆ ---        ┆ ---       ┆ ---       ┆ ---      ┆ ---       ┆ ---       ┆ ---        ┆ ---       ┆ ---       ┆ ---        ┆ ---        ┆ ---         │
│ str       ┆ i64       ┆ f64      ┆ f64         ┆ f64        ┆ f64       ┆ f64       ┆ f64      ┆ f64       ┆ f64       ┆ f64        ┆ f64       ┆ f64       ┆ f64        ┆ f64        ┆ f64         │
╞═══════════╪═══════════╪══════════╪═════════════╪════════════╪═══════════╪═══════════╪══════════╪═══════════╪═══════════╪════════════╪═══════════╪═══════════╪════════════╪═

policy_lift 8
shape: (10, 5)
┌───────────┬──────────┬───────────────┬───────────────┬──────────────┐
│ policy    ┆ share    ┆ lift_3        ┆ lift_10       ┆ lift_100     │
│ ---       ┆ ---      ┆ ---           ┆ ---           ┆ ---          │
│ str       ┆ f64      ┆ f64           ┆ f64           ┆ f64          │
╞═══════════╪══════════╪═══════════════╪═══════════════╪══════════════╡
│ policy_P0 ┆ 1.0      ┆ 1.8437e6      ┆ 675825.153371 ┆ 90449.344592 │
│ policy_P1 ┆ 0.973614 ┆ 76210.129245  ┆ 46709.266612  ┆ 14240.097062 │
│ policy_P2 ┆ 0.971707 ┆ 117256.366303 ┆ 71866.54753   ┆ 20484.649132 │
│ policy_P3 ┆ 0.958264 ┆ 69198.559826  ┆ 53966.355296  ┆ 17498.949804 │
│ policy_P4 ┆ 0.577707 ┆ 56307.305707  ┆ 43041.203635  ┆ 14466.033858 │
│ policy_P5 ┆ 0.999999 ┆ 16189.935766  ┆ 15831.247897  ┆ 11261.716974 │
│ policy_P6 ┆ 0.999703 ┆ 84077.780088  ┆ 51297.398947  ┆ 16211.675126 │
│ policy_P7 ┆ 0.9      ┆ 17.25611      ┆ 17.25611      ┆ 17.25611     │
│ policy_P8 ┆ 0.554895 ┆ 91460.3030

holdout 8
shape: (39, 4)
┌────────────────────┬─────────┬───────────┬──────────┐
│ policy             ┆ guesses ┆ in_sample ┆ held_out │
│ ---                ┆ ---     ┆ ---       ┆ ---      │
│ str                ┆ i64     ┆ f64       ┆ f64      │
╞════════════════════╪═════════╪═══════════╪══════════╡
│ policy_P0          ┆ 3       ┆ 0.05531   ┆ 0.055321 │
│ policy_P0          ┆ 10      ┆ 0.067583  ┆ 0.067595 │
│ policy_P0          ┆ 100     ┆ 0.090449  ┆ 0.090455 │
│ policy_P1          ┆ 3       ┆ 0.002348  ┆ 0.002347 │
│ policy_P1          ┆ 10      ┆ 0.004798  ┆ 0.004797 │
│ policy_P1          ┆ 100     ┆ 0.014626  ┆ 0.014624 │
│ policy_P2          ┆ 3       ┆ 0.00362   ┆ 0.003622 │
│ policy_P2          ┆ 10      ┆ 0.007396  ┆ 0.007392 │
│ policy_P2          ┆ 100     ┆ 0.021081  ┆ 0.021074 │
│ policy_P3          ┆ 3       ┆ 0.002166  ┆ 0.002164 │
│ policy_P3          ┆ 10      ┆ 0.005632  ┆ 0.00563  │
│ policy_P3          ┆ 100     ┆ 0.018261  ┆ 0.018261 │
│ policy_P4          ┆ 